# gridkit_viz
Plotting notebook for a completed GridKit UQ experiment.
Set `UQ_RUN_ROOT` below to point at any experiment directory.

In [1]:
import pandas as pd
import numpy as np
import os
import pyarrow.parquet as pq
import plotly.express as px
import plotly.graph_objects as go
from collections import defaultdict
from IPython.core.interactiveshell import InteractiveShell

InteractiveShell.ast_node_interactivity = "all"
pd.options.plotting.backend = "plotly"

In [2]:
# === Experiment config — change this to switch experiments ===
UQ_RUN_ROOT = "/kfs2/projects/scidac/scidac-data/gridkit-runs/hawaii-v1"
UQ_RUN_ROOT = "/kfs2/projects/scidac/scidac-data/gridkit-runs/hawaii-v2"
# UQ_RUN_ROOT = "/kfs2/projects/scidac/scidac-data/gridkit-runs/threebusbasic-v1"

SERIALIZE_MODE = "per_run"  # "stacked" or "per_run" — must match how data was collected
UQ_OUT_PATH = (
    os.path.join(UQ_RUN_ROOT, "results.parquet")
    if SERIALIZE_MODE == "stacked"
    else os.path.join(UQ_RUN_ROOT, "runs")
)

SEED = 42

print(f"UQ_RUN_ROOT:    {UQ_RUN_ROOT}")
print(f"SERIALIZE_MODE: {SERIALIZE_MODE}")
print(f"UQ_OUT_PATH:    {UQ_OUT_PATH}")
print(f"path exists:    {os.path.exists(UQ_OUT_PATH)}")

UQ_RUN_ROOT:    /kfs2/projects/scidac/scidac-data/gridkit-runs/hawaii-v2
SERIALIZE_MODE: per_run
UQ_OUT_PATH:    /kfs2/projects/scidac/scidac-data/gridkit-runs/hawaii-v2/runs
path exists:    True


In [3]:
# === Load / index data ===
if SERIALIZE_MODE == "stacked":
    results_df = pq.read_table(UQ_OUT_PATH).to_pandas()
    all_run_ids = sorted(results_df["run_id"].unique())
    mem_mb = results_df.memory_usage(deep=True).sum() / 1024**2
    disk_mb = os.path.getsize(UQ_OUT_PATH) / 1024**2
    print(f"results_df: {results_df.shape[0]:,} rows × {results_df.shape[1]} cols")
    print(f"  in-memory: {mem_mb:.1f} MB")
    print(f"  on disk: {disk_mb:.2f} MB (single file)")
    print(f"  run_ids ({len(all_run_ids)}): {all_run_ids}")
    results_df.head()
else:
    import glob

    run_files = sorted(glob.glob(os.path.join(UQ_OUT_PATH, "run_*.parquet")))
    if not run_files:
        raise FileNotFoundError(f"No run_*.parquet files found in {UQ_OUT_PATH}")

    run_id_to_file = {
        int(os.path.basename(f).replace("run_", "").replace(".parquet", "")): f
        for f in run_files
    }
    all_run_ids = sorted(run_id_to_file)

    total_disk_mb = sum(os.path.getsize(f) for f in run_files) / 1024**2
    print(f"per_run index: {len(run_files)} files in {UQ_OUT_PATH}")
    print(
        f"  on disk: {total_disk_mb:.2f} MB  ({total_disk_mb/len(run_files):.3f} MB/run)"
    )
    print(
        f"  run_ids ({len(all_run_ids)}): {all_run_ids[:10]}{'...' if len(all_run_ids) > 10 else ''}"
    )

    def _load_runs(ids):
        """Read and concat a subset of per-run parquet files. Injects run_id column."""
        frames = []
        for rid in ids:
            df = pq.read_table(run_id_to_file[rid]).to_pandas()
            df.insert(0, "run_id", rid)
            frames.append(df)
        return pd.concat(frames, ignore_index=True)

per_run index: 1000 files in /kfs2/projects/scidac/scidac-data/gridkit-runs/hawaii-v2/runs
  on disk: 3369.03 MB  (3.369 MB/run)
  run_ids (1000): [0, 1, 2, 3, 4, 5, 6, 7, 8, 9]...


In [4]:
# === Build column groups (shared by all plots) ===
# For stacked: use results_df columns. For per_run: read schema from one file (no data loaded).
if SERIALIZE_MODE == "stacked":
    _schema_cols = list(results_df.columns)
else:
    _schema_cols = [f.name for f in pq.read_schema(run_files[0])]

meta_cols = {"run_id", "time", "Solver Status"}
param_cols = [
    c
    for c in _schema_cols
    if c not in meta_cols and "_" in c and c.split("_")[-1] in {"H", "D", "Ra"}
]  # extend suffix set as needed
skip_cols = meta_cols | set(param_cols)
mon_cols = [c for c in _schema_cols if c not in skip_cols]

col_groups = defaultdict(list)
for col in mon_cols:
    parts = col.split("_")
    key = ("Bus", parts[-1]) if parts[0] == "Bus" else (parts[0], parts[-1])
    col_groups[key].append(col)

print(f"Monitor signal groups ({len(col_groups)}):")
for k, v in sorted(col_groups.items()):
    print(f"  {k[0]}-{k[1]}: {len(v)} signals")

Monitor signal groups (4):
  Bus-Va: 37 signals
  Bus-Vm: 37 signals
  Genrou-delta: 39 signals
  Genrou-omega: 39 signals


# plotting

In [5]:
# === Plot 1: subsample of runs × subsample of buses/gens, one plot per (element, var) ===
# Lines colored by signal; runs of the same signal appear as a bundle (showing UQ spread)
PLOT_MAX_RUNS = 5
PLOT_MAX_BUS_N = 5  # max bus signals per plot
PLOT_MAX_GEN_N = 3  # max gen signals per plot

# --- optional: pin specific runs (comment out to use random subsample) ---
# PLOT_RUN_IDS = [0, 1, 2]

# --- optional: pin specific signals (comment out to use random subsample) ---
# PLOT_BUS_SIGNALS = ["Bus_ALOHA138_Vm", "Bus_ALOHA138_Va"]
# PLOT_GEN_SIGNALS = ["Genrou_2_1_omega", "Genrou_23_1_omega"]

rng_plot = np.random.default_rng(SEED)

if "PLOT_RUN_IDS" in globals():
    plot_run_ids = PLOT_RUN_IDS
    print(f"Runs: pinned {plot_run_ids}")
elif len(all_run_ids) > PLOT_MAX_RUNS:
    plot_run_ids = list(rng_plot.choice(all_run_ids, size=PLOT_MAX_RUNS, replace=False))
    print(f"Runs: {PLOT_MAX_RUNS} of {len(all_run_ids)} (random subsample)")
else:
    plot_run_ids = all_run_ids
    print(f"Runs: all {len(all_run_ids)}")

if SERIALIZE_MODE == "stacked":
    plot_df = results_df[results_df["run_id"].isin(plot_run_ids)]
else:
    plot_df = _load_runs(plot_run_ids)

for (elem, var), cols in sorted(col_groups.items()):
    is_bus = elem == "Bus"
    max_n = PLOT_MAX_BUS_N if is_bus else PLOT_MAX_GEN_N
    pinned_key = "PLOT_BUS_SIGNALS" if is_bus else "PLOT_GEN_SIGNALS"

    if pinned_key in globals():
        plot_cols = [c for c in globals()[pinned_key] if c in cols]
        sig_note = f"{len(plot_cols)} pinned of {len(cols)} signals"
    elif len(cols) > max_n:
        plot_cols = list(rng_plot.choice(cols, size=max_n, replace=False))
        sig_note = f"{max_n} of {len(cols)} signals (random)"
    else:
        plot_cols = cols
        sig_note = f"all {len(cols)} signal(s)"

    if not plot_cols:
        continue

    melted = plot_df[["time", "run_id"] + plot_cols].melt(
        id_vars=["time", "run_id"], var_name="signal", value_name=var
    )
    fig = px.line(
        melted,
        x="time",
        y=var,
        color="signal",
        line_group="run_id",
        title=f"{elem} {var} — {sig_note}, {len(plot_run_ids)} runs",
        labels={"time": "Time (s)", var: var},
    )
    _ = fig.update_traces(opacity=0.6)
    _ = fig.update_layout(legend_title="signal")
    _ = fig.show()

Runs: 5 of 1000 (random subsample)


In [6]:
# === Plot 2: one run, all buses/gens, one plot per (element, var) ===
# Also produces a post-fault zoom (t > T_ZOOM_START) to reveal small oscillations
PLOT_RUN_ID = 0  # which run to inspect
T_ZOOM_START = 1.2  # zoom window start (s) — set just after fault clears

if PLOT_RUN_ID not in all_run_ids:
    print(f"run_id={PLOT_RUN_ID} not found; available: {all_run_ids}")
else:
    if SERIALIZE_MODE == "stacked":
        single_run_df = results_df[results_df["run_id"] == PLOT_RUN_ID]
    else:
        single_run_df = _load_runs([PLOT_RUN_ID])

    print(f"Plotting run_id={PLOT_RUN_ID} — all signals")
    zoom_df = single_run_df[single_run_df["time"] >= T_ZOOM_START]

    for (elem, var), cols in sorted(col_groups.items()):
        melted = single_run_df[["time"] + cols].melt(
            id_vars=["time"], var_name="signal", value_name=var
        )
        fig = px.line(
            melted,
            x="time",
            y=var,
            color="signal",
            title=f"{elem} {var} — run {PLOT_RUN_ID}, all {len(cols)} signal(s)",
            labels={"time": "Time (s)", var: var},
        )
        _ = fig.update_layout(legend_title="signal")
        _ = fig.show()

        # zoom: post-fault only — reveals oscillations hidden by fault transient scale
        melted_z = zoom_df[["time"] + cols].melt(
            id_vars=["time"], var_name="signal", value_name=var
        )
        fig_z = px.line(
            melted_z,
            x="time",
            y=var,
            color="signal",
            title=f"{elem} {var} — run {PLOT_RUN_ID}, post-fault zoom (t ≥ {T_ZOOM_START}s)",
            labels={"time": "Time (s)", var: var},
        )
        _ = fig_z.update_layout(legend_title="signal")
        _ = fig_z.show()

Plotting run_id=0 — all signals


In [7]:
# === Plot 3: list of signals × subsample of runs — one plot per signal ===
# Signals chosen by proximity to fault (ALOHA138, bus 1):
#   Buses:  ALOHA138 (faulted), KALAELOA138 (1-hop, X=0.042), WAIPAHU138 (1-hop, X=0.024), KAHE138 (2-hop, X≈0.050)
#   Gens:   bus 2=ALOHA69 (1-hop), bus 35=KALAELOA138 (1-hop, UQ-sampled H),
#           bus 23=WAIPAHU69 (2-hop, UQ-sampled H), bus 34=SCHOFIELD69 (3+ hops, UQ-sampled H)
PLOT3_MAX_RUNS = 10  # max runs to overlay (None = all)
PLOT3_SIGNALS = [
    # --- buses: fault site + 1-hop + 2-hop low-Z ---
    "Bus_ALOHA138_Va",  # bus 1 — faulted bus
    "Bus_KALAELOA138_Va",  # bus 35 — 1-hop (X=0.042), has UQ-sampled gens
    "Bus_WAIPAHU138_Va",  # bus 22 — 1-hop (X=0.024)
    "Bus_KAHE138_Va",  # bus 37 — 2-hop, lowest-Z path (X≈0.050)
    # --- gens: ordered by distance from fault ---
    "Genrou_2_1_omega",  # bus 2=ALOHA69, 1-hop — expect largest swing
    "Genrou_2_1_delta",
    "Genrou_35_1_omega",  # bus 35=KALAELOA138, 1-hop, UQ-sampled H
    "Genrou_35_1_delta",
    "Genrou_23_1_omega",  # bus 23=WAIPAHU69, 2-hop, UQ-sampled H
    "Genrou_23_1_delta",
    "Genrou_34_1_omega",  # bus 34=SCHOFIELD69, 3+ hops, UQ-sampled H — expect smallest swing
    "Genrou_34_1_delta",
]

# hop annotation for plot titles
_sig_hops = {
    "Bus_ALOHA138_Va": "faulted bus",
    "Bus_KALAELOA138_Va": "1-hop (X=0.042)",
    "Bus_WAIPAHU138_Va": "1-hop (X=0.024)",
    "Bus_KAHE138_Va": "2-hop (X≈0.050)",
    "Genrou_2_1_omega": "bus 2=ALOHA69, 1-hop",
    "Genrou_2_1_delta": "bus 2=ALOHA69, 1-hop",
    "Genrou_35_1_omega": "bus 35=KALAELOA138, 1-hop",
    "Genrou_35_1_delta": "bus 35=KALAELOA138, 1-hop",
    "Genrou_23_1_omega": "bus 23=WAIPAHU69, 2-hop",
    "Genrou_23_1_delta": "bus 23=WAIPAHU69, 2-hop",
    "Genrou_34_1_omega": "bus 34=SCHOFIELD69, 3+ hops",
    "Genrou_34_1_delta": "bus 34=SCHOFIELD69, 3+ hops",
}

if PLOT3_MAX_RUNS is not None and len(all_run_ids) > PLOT3_MAX_RUNS:
    rng3 = np.random.default_rng(SEED)
    run_ids3 = list(rng3.choice(all_run_ids, size=PLOT3_MAX_RUNS, replace=False))
    runs_note = f"{PLOT3_MAX_RUNS} of {len(all_run_ids)} runs (random subsample)"
else:
    run_ids3 = all_run_ids
    runs_note = f"all {len(all_run_ids)} runs"

if SERIALIZE_MODE == "stacked":
    plot3_df = results_df[results_df["run_id"].isin(run_ids3)]
    available = set(results_df.columns)
else:
    plot3_df = _load_runs(run_ids3)
    available = set(_schema_cols)

for sig in PLOT3_SIGNALS:
    if sig not in available:
        print(f"  WARNING: '{sig}' not found, skipping")
        continue
    hops_note = _sig_hops.get(sig, "")
    title = (
        f"{sig} {runs_note} <br> [{hops_note}]" if hops_note else f"{sig} — {runs_note}"
    )
    fig = px.line(
        plot3_df[["time", "run_id", sig]],
        x="time",
        y=sig,
        color="run_id",
        title=title,
        labels={"time": "Time (s)", sig: sig, "run_id": "Run"},
    )
    _ = fig.update_layout(legend_title="run_id")
    _ = fig.show()

# viz sampling methods

In [8]:
# === LHS vs Random sampling comparison: U[0,1] x U[0,1] ===
from scipy.stats.qmc import LatinHypercube
import plotly.graph_objects as go

N = 10  # keep small to make the LHS stratification visually obvious
rng = np.random.default_rng(42)

# Random
rand_pts = rng.uniform(size=(N, 2))

# LHS
sampler = LatinHypercube(d=2, seed=42)
lhs_pts = sampler.random(N)

fig = go.Figure()
_ = fig.add_trace(
    go.Scatter(
        x=rand_pts[:, 0],
        y=rand_pts[:, 1],
        mode="markers",
        name="Random",
        marker=dict(symbol="circle", size=12, color="steelblue", opacity=0.8),
    )
)
_ = fig.add_trace(
    go.Scatter(
        x=lhs_pts[:, 0],
        y=lhs_pts[:, 1],
        mode="markers",
        name="LHS",
        marker=dict(symbol="x", size=14, color="tomato", opacity=0.9),
    )
)

# grid lines showing N x N strata — LHS guarantees exactly 1 point per row & column
for k in range(N + 1):
    v = k / N
    _ = fig.add_hline(y=v, line=dict(color="rgba(150,150,150,0.5)", width=1))
    _ = fig.add_vline(x=v, line=dict(color="rgba(150,150,150,0.5)", width=1))

_ = fig.update_layout(
    title=f"LHS vs Random (N={N}): LHS has exactly 1 point per row & column",
    xaxis_title="x",
    yaxis_title="y",
    xaxis=dict(range=[-0.02, 1.02]),
    yaxis=dict(range=[-0.02, 1.02], scaleanchor="x"),
    legend=dict(x=0.01, y=0.99),
    width=600,
    height=600,
)
_ = fig.show()